In [0]:
from pyspark.sql import functions as f
from pyspark.sql.window import Window as window

def parametro(nome, padrao):
    try:
        return dbutils.widgets.get(nome)
    except Exception:
        dbutils.widgets.text(nome, padrao)
        return dbutils.widgets.get(nome)

catalogo = parametro("catalogo", "workspace")
spark.sql(f"use catalog `{catalogo.replace('`', '``')}`")

from datetime import date, timedelta, datetime
spark.sql("create schema if not exists silver")
hoje = date.today()
di = parametro("data_inicio", "").strip()
dfim = parametro("data_fim", "").strip()
inicio = datetime.strptime(di, "%m-%d-%Y").date() if di else hoje - timedelta(days=7)
fim = datetime.strptime(dfim, "%m-%d-%Y").date() if dfim else hoje
if inicio > fim:
    raise ValueError("Intervalo de datas inválido")


In [0]:
def gravar_silver(df, tabela):
    df.write.format("delta").mode("overwrite").option("overwriteSchema", "true").saveAsTable(tabela)

def mais_recente(df):
    cols = sorted(c for c in df.columns if c != "ingestion_datetime")
    assinatura = f.sha2(f.to_json(f.struct(*[f.col(c) for c in cols])), 256)
    w = window.partitionBy("id").orderBy(f.col("ingestion_datetime").desc_nulls_last(), assinatura.desc())
    return (df.filter(f.col("id").isNotNull() & (f.trim(f.col("id")) != ""))
            .withColumn("_rn", f.row_number().over(w)).filter("_rn = 1").drop("_rn"))

def limpar_numero(nome, moeda=False, inteiro=False):
    x = f.trim(f.col(nome).cast("string"))
    if moeda:
        x = f.regexp_replace(x, r"(?i)^(?:US\$|R\$|USD|BRL|\$)\s*", "")
        x = f.regexp_replace(x, r"(?i)\s*(?:USD|BRL)$", "")
    x = f.trim(x)
    x = f.when(x.rlike(r"^[+-]?\d{1,3}(?:[ \u00a0]\d{3})+(?:[.,]\d+)?$"),
               f.regexp_replace(x, r"[ \u00a0]", "")).otherwise(x)
    br = x.rlike(r"^[+-]?\d{1,3}(?:\.\d{3})+,\d+$")
    us = x.rlike(r"^[+-]?\d{1,3}(?:,\d{3})+\.\d+$")
    milhares_virgula = x.rlike(r"^[+-]?\d{1,3}(?:,\d{3})+$")
    milhares_ponto = x.rlike(r"^[+-]?\d{1,3}(?:\.\d{3})+$")
    simples = x.rlike(r"^[+-]?\d+(?:[.,]\d+)?$")
    resultado = (f.when(br, f.regexp_replace(f.regexp_replace(x, r"\.", ""), ",", "."))
                 .when(us, f.regexp_replace(x, ",", "")))
    if moeda or inteiro:
        resultado = (resultado.when(milhares_virgula, f.regexp_replace(x, ",", ""))
                     .when(milhares_ponto, f.regexp_replace(x, r"\.", "")))
    else:
        resultado = (resultado.when(x.rlike(r"^[+-]?\d{1,3}(?:,\d{3}){2,}$"), f.regexp_replace(x, ",", ""))
                     .when(x.rlike(r"^[+-]?\d{1,3}(?:\.\d{3}){2,}$"), f.regexp_replace(x, r"\.", "")))
    return resultado.when(simples, f.regexp_replace(x, ",", ".")).otherwise(f.lit(None).cast("string"))


In [0]:
df_cotacao = (spark.table("bronze.tb_cotacao_dolar")
    .withColumn("data_hora_cotacao", f.expr("try_cast(dataHoraCotacao as timestamp)"))
    .withColumn("data_cotacao", f.to_date("data_hora_cotacao"))
    .withColumn("cotacao_compra", f.expr("try_cast(cotacaoCompra as decimal(18,6))"))
    .filter(f.col("data_cotacao").isNotNull() & (f.col("cotacao_compra") > 0)))
w = window.partitionBy("data_cotacao").orderBy(
    f.col("data_hora_cotacao").desc(), f.col("ingestion_datetime").desc(), f.col("cotacao_compra").desc())
df_cotacao = (df_cotacao.withColumn("_rn", f.row_number().over(w))
    .filter("_rn = 1").select("data_cotacao", "cotacao_compra"))

limites = df_cotacao.agg(f.min("data_cotacao").alias("data_min")).first()
if limites["data_min"] is None:
    raise ValueError("Nenhuma cotação válida na Bronze")
if not df_cotacao.filter(f.col("data_cotacao") <= f.lit(inicio)).limit(1).count():
    raise ValueError("Não há cotação anterior ao início solicitado para forward fill")

calendario = spark.range(1).select(f.explode(f.sequence(
    f.lit(limites["data_min"]), f.lit(fim), f.expr("interval 1 day")
)).alias("data_cotacao"))
w_ffill = window.orderBy("data_cotacao").rowsBetween(window.unboundedPreceding, window.currentRow)
df_cotacao_silver = (calendario.join(df_cotacao, "data_cotacao", "left")
    .withColumn("cotacao_compra", f.last("cotacao_compra", ignorenulls=True).over(w_ffill)))
gravar_silver(df_cotacao_silver, "silver.tb_cotacao_dolar")
display(df_cotacao_silver.filter(f.col("data_cotacao") >= f.lit(inicio)).orderBy("data_cotacao"))


/databricks/python/lib/python3.12/site-packages/pyspark/sql/connect/expressions.py:1155: UserWarning: WARN WindowExpression: No Partition Defined for Window operation! Moving all data to a single partition, this can cause serious performance degradation.
  warnings.warn(


data_cotacao,cotacao_compra
2026-10-09,4.988600
2026-10-10,4.988600
2026-10-11,4.988600
2026-10-12,4.988600
2026-10-13,5.009000
2026-10-14,5.043500
2026-10-15,5.051500
2026-10-16,5.051500


In [0]:
df_info = mais_recente(spark.table("bronze.tb_movies_info"))

df_info = (
    df_info
    .withColumn(
        "_status",
        f.lower(
            f.trim(
                f.regexp_replace(
                    f.regexp_replace(f.col("status").cast("string"), r"[^a-zA-Z]+", " "),
                    r"\s+",
                    " "
                )
            )
        )
    )
    .withColumn(
        "status_filme",
        f.when(f.col("_status") == "released", "Lançado")
        .when(f.col("_status") == "post production", "Pós-Produção")
        .when(f.col("_status") == "in production", "Em Produção")
        .when(f.col("_status") == "planned", "Planejado")
        .when(f.col("_status") == "rumored", "Rumores")
        .when(f.col("_status").isin("canceled", "cancelled"), "Cancelado")
        .otherwise("Não Informado")
    )
    .withColumn(
        "data_lancamento",
        f.coalesce(
            f.expr("try_to_timestamp(trim(release_date), 'yyyy-MM-dd')"),
            f.expr("try_to_timestamp(trim(release_date), 'dd/MM/yyyy')"),
            f.expr("try_to_timestamp(trim(release_date), 'MM/dd/yyyy')"),
            f.expr("try_to_timestamp(trim(release_date), 'dd-MM-yyyy')"),
            f.expr("try_to_timestamp(trim(release_date), 'MM-dd-yyyy')"),
            f.expr("try_to_timestamp(trim(release_date), 'yyyy/MM/dd')")
        ).cast("date")
    )
)

df_info_silver = (
    df_info
    .select(
        f.col("id").cast("string").alias("id_filme"),
        f.col("title").alias("titulo"),
        f.col("original_title").alias("titulo_original"),
        "data_lancamento",
        f.expr("try_cast(runtime as int)").alias("duracao_minutos"),
        f.col("original_language").alias("idioma_original"),
        "status_filme",
        f.col("overview").alias("sinopse"),
        f.col("tagline").alias("frase_divulgacao")
    )
    .withColumn(
        "duracao_minutos",
        f.when(f.col("duracao_minutos") > 0, f.col("duracao_minutos"))
    )
    .withColumn("ano_lancamento", f.year("data_lancamento"))
)

(
    df_info_silver.write
    .format("delta")
    .mode("overwrite")
    .option("overwriteSchema", "true")
    .saveAsTable("silver.tb_info_filmes")
)

display(df_info_silver)


id_filme,titulo,titulo_original,data_lancamento,duracao_minutos,idioma_original,status_filme,sinopse,frase_divulgacao,ano_lancamento
1000004,Purple Beatz,Purple Beatz,2022-07-07,86,en,Lançado,"Sarah-Jane is a young aspiring jazz singer from Bournemouth who moves to London to embark on a music career. Not long in town, she falls for the handsome Airbeats, but also sinister music producer Russell-D, who represents a darker side to the music industry.",A drum n bass romance.,2022
1000030,58 Hours: The Baby Jessica Story,58 Hours: The Baby Jessica Story,2021-07-31,null,es,Lançado,null,null,2021
1000079,Pourquoi tu souris ?,Pourquoi tu souris ?,2024-06-26,null,fr,Em Produção,null,null,2024
1000099,Chowdhury Rajbari,Chowdhury Rajbari,2017-08-12,131,bn,Lançado,"Giaa and Arnab are a married couple, who visit Arnab's ancestral palace 'Chowdhury Rajbari' for a romantic getaway. Once there, Giaa experiences strange occurrences and memories of a past life. In her search for truth, Giaa comes across Dr. Oindrila, who assists her in her search. But trouble starts when they come across more questions, instead of answers.",null,2017
1000110,Les Enfants rouges,Les Enfants rouges,2023-10-25,null,fr,Lançado,null,null,2023
1000116,Don't Wait for Me,אל תחכי לי,2021-10-21,88,he,Lançado,Matan arrives in a crime neighborhood after his father goes bankrupt and loses their home.,null,2021
1000156,The Kids of Santa Fe: The Largest Unknown Mass Shooting,The Kids of Santa Fe: The Largest Unknown Mass Shooting,2021-09-10,120,en,Lançado,On 2018 a student at Santa Fe High School executed 10 people and wounded 13 others. The shooting took half an hour before the killer was arrested. The movie is about the students that were directly affected and what they are doing today.,null,2021
1000517,The Temple Woods Gang,Le gang des bois du temple,2022-10-16,116,fr,Lançado,"A retired military man lives in the Temple Woods housing project. Just as he’s burying his mother, his neighbour Bébé, who belongs to a gang of robbers from the area, is preparing to rob the convoy of a wealthy Arab prince.",null,2022
1000643,Mise au vert,Mise au vert,2023-09-20,null,fr,Lançado,"To strengthen family ties, to free his teenagers from their digital addiction, to reconnect with his roots in the region of his childhood; this is why Régis decides to take his wife and children on a surprise vacation in the Vercors. An old ruined house lost in the forest. No water, no electricity, even less network or wifi. Nothing is going to happen as planned",null,2023
1000780,"You Sing Loud, I Sing Louder","You Sing Loud, I Sing Louder",2023-03-11,102,en,Lançado,"In an effort to reunite with his daughter after a period of absence, a father takes her on a road trip to Santa Fe, New Mexico. Along the way they encounter some interesting characters and obstacles while sorting out their relationship.",null,2023


In [0]:
df_fin = mais_recente(spark.table("bronze.tb_movies_financials"))

df_fin = (
    df_fin
    .withColumn("_budget", limpar_numero("budget", moeda=True))
    .withColumn("_revenue", limpar_numero("revenue", moeda=True))
    .withColumn("orcamento_usd", f.expr("try_cast(_budget as decimal(18,2))"))
    .withColumn("receita_usd", f.expr("try_cast(_revenue as decimal(18,2))"))
    .withColumn("orcamento_usd", f.when(f.col("orcamento_usd") > 0, f.col("orcamento_usd")))
    .withColumn("receita_usd", f.when(f.col("receita_usd") > 0, f.col("receita_usd")))
)

taxa = (
    spark.table("silver.tb_cotacao_dolar")
    .filter(f.col("cotacao_compra").isNotNull())
    .orderBy(f.col("data_cotacao").desc())
    .limit(1)
    .select(f.col("cotacao_compra").alias("taxa_dolar"))
)

df_fin_silver = (
    df_fin
    .crossJoin(taxa)
    .withColumn("orcamento_brl", (f.col("orcamento_usd") * f.col("taxa_dolar")).cast("decimal(18,2)"))
    .withColumn("receita_brl", (f.col("receita_usd") * f.col("taxa_dolar")).cast("decimal(18,2)"))
    .withColumn("lucro_usd", (f.col("receita_usd") - f.col("orcamento_usd")).cast("decimal(18,2)"))
    .withColumn("lucro_brl", (f.col("receita_brl") - f.col("orcamento_brl")).cast("decimal(18,2)"))
    .withColumn(
        "margem_lucro_percentual",
        f.when(
            f.col("orcamento_usd").isNotNull() & f.col("receita_usd").isNotNull() & (f.col("receita_usd") > 0),
            f.round(((f.col("receita_usd") - f.col("orcamento_usd")) / f.col("receita_usd")) * 100, 2)
        )
    )
    .select(
        f.col("id").cast("string").alias("id_filme"),
        "orcamento_usd",
        "receita_usd",
        "orcamento_brl",
        "receita_brl",
        "lucro_usd",
        "lucro_brl",
        f.col("margem_lucro_percentual").cast("double")
    )
)

(
    df_fin_silver.write
    .format("delta")
    .mode("overwrite")
    .option("overwriteSchema", "true")
    .saveAsTable("silver.tb_financeiro_filmes")
)

display(df_fin_silver)


id_filme,orcamento_usd,receita_usd,orcamento_brl,receita_brl,lucro_usd,lucro_brl,margem_lucro_percentual
1000005,null,null,null,null,null,null,null
1000030,null,null,null,null,null,null,null
1000092,null,null,null,null,null,null,null
1000094,null,null,null,null,null,null,null
1000197,null,null,null,null,null,null,null
1000221,null,null,null,null,null,null,null
1000569,null,null,null,null,null,null,null
1000593,null,null,null,null,null,null,null
1000643,null,null,null,null,null,null,null
1000988,null,null,null,null,null,null,null


In [0]:
df_met = mais_recente(spark.table("bronze.tb_movies_metrics"))

df_met = (
    df_met
    .withColumn("_popularidade", limpar_numero("popularity"))
    .withColumn("_nota_tmdb", limpar_numero("vote_average"))
    .withColumn("_qtd_tmdb", limpar_numero("vote_count", inteiro=True))
    .withColumn("_nota_imdb", limpar_numero("averageRating"))
    .withColumn("_qtd_imdb", limpar_numero("numVotes", inteiro=True))
    .withColumn("popularidade", f.expr("try_cast(_popularidade as double)"))
    .withColumn("nota_media_tmdb", f.expr("try_cast(_nota_tmdb as double)"))
    .withColumn("qtd_votos_tmdb", f.expr("case when try_cast(_qtd_tmdb as decimal(38,10)) = floor(try_cast(_qtd_tmdb as decimal(38,10))) then try_cast(try_cast(_qtd_tmdb as decimal(38,10)) as int) end"))
    .withColumn("nota_media_imdb", f.expr("try_cast(_nota_imdb as double)"))
    .withColumn("qtd_votos_imdb", f.expr("case when try_cast(_qtd_imdb as decimal(38,10)) = floor(try_cast(_qtd_imdb as decimal(38,10))) then try_cast(try_cast(_qtd_imdb as decimal(38,10)) as int) end"))
)

df_met_silver = (
    df_met
    .select(
        f.col("id").cast("string").alias("id_filme"),
        f.when((f.col("popularidade") >= 0), f.col("popularidade")).alias("popularidade"),
        f.when(f.col("nota_media_tmdb").between(0, 10), f.col("nota_media_tmdb")).alias("nota_media_tmdb"),
        f.when(f.col("qtd_votos_tmdb") >= 0, f.col("qtd_votos_tmdb")).alias("qtd_votos_tmdb"),
        f.when(f.col("nota_media_imdb").between(0, 10), f.col("nota_media_imdb")).alias("nota_media_imdb"),
        f.when(f.col("qtd_votos_imdb") >= 0, f.col("qtd_votos_imdb")).alias("qtd_votos_imdb")
    )
)

(
    df_met_silver.write
    .format("delta")
    .mode("overwrite")
    .option("overwriteSchema", "true")
    .saveAsTable("silver.tb_metricas_engajamento")
)

display(df_met_silver)

campos = [("popularity", "popularidade"), ("vote_average", "nota_media_tmdb"),
          ("vote_count", "qtd_votos_tmdb"), ("averageRating", "nota_media_imdb"),
          ("numVotes", "qtd_votos_imdb")]
auditoria = df_met.select("id", *[a for a, _ in campos]).join(
    df_met_silver, f.col("id") == f.col("id_filme"), "inner")
display(auditoria.agg(*[
    f.sum(f.when(f.col(a).isNotNull() & (f.trim(f.col(a)) != "") & f.col(b).isNull(), 1).otherwise(0))
     .alias("rejeitados_" + b) for a, b in campos
]))
display(auditoria.filter(f.col("popularity").isNotNull() & f.col("popularidade").isNull())
    .select("id", "popularity").limit(20))


id_filme,popularidade,nota_media_tmdb,qtd_votos_tmdb,nota_media_imdb,qtd_votos_imdb
1000092,4.797,8.5,1,6.8,130
1000094,2.645,6.9,28,6.5,null
1000197,2.552,6.0,4,5.9,183
1000221,0.914,10.0,1,7.5,93
1000569,2.576,0.0,0,5.8,448
1000593,null,null,null,null,null
1000643,4.412,5.0,1,5.0,88
1000988,1.674,6.8,4,6.4,86
1001017,0.6,6.0,1,5.9,11
1001203,null,0.0,0,null,null


rejeitados_popularidade,rejeitados_nota_media_tmdb,rejeitados_qtd_votos_tmdb,rejeitados_nota_media_imdb,rejeitados_qtd_votos_imdb
3535,3663,403,1986,2415


id,popularity
1002430,"and an insight into a traditional educational system that fosters good character-building based on a peaceful religious teaching that has been practiced in Indonesia for centuries, Raising their students to respect and to have compassion towards others despite their differences"
1004657,Sophia. They were married for 36 years
1008091,or rather to Jonah. Frustrations arise as members of the family struggle to fight their human urges
1012763,the parents give Jonah some space
1015381,Tucker. But sparks fly when Frankie meets Jack
1019231,misunderstanding and lots of banter. Enter the same girl again. You know where it's heading! Oh yes
1029479,"\\"" Naoki Kazama works for Nemesis Detective Agency and is regarded as a brilliant detective. He is able to solve the most difficult of cases"""
1029645,from ancient to modern
1030221,"\\"" said Marx; this film"""
1030586,"and part of the population arming itself on the expectation of something wicked coming our way in the most polarized election ever.\"",0.0,0,Caetano W. Galindo"


In [0]:
df_reviews_silver = (
    spark.table("bronze.tb_movies_reviews")
    .withColumn("_nota", limpar_numero("nota"))
    .withColumn("nota_usuario", f.expr("try_cast(_nota as double)"))
    .withColumn(
        "nota_usuario",
        f.when(f.col("nota_usuario").between(0, 10), f.col("nota_usuario"))
    )
    .withColumn(
        "comentario_usuario",
        f.when(
            f.col("comentario").isNull() | (f.trim(f.col("comentario").cast("string")) == ""),
            f.lit("Sem comentário")
        ).otherwise(f.trim(f.col("comentario").cast("string")))
    )
    .select(
        f.col("id").cast("string").alias("id_filme"),
        f.trim(f.col("nome").cast("string")).alias("nome_usuario"),
        "nota_usuario",
        "comentario_usuario"
    )
    .dropDuplicates(["id_filme", "nome_usuario", "nota_usuario", "comentario_usuario"])
)

(
    df_reviews_silver.write
    .format("delta")
    .mode("overwrite")
    .option("overwriteSchema", "true")
    .saveAsTable("silver.tb_avaliacoes_usuarios")
)

display(df_reviews_silver)


id_filme,nome_usuario,nota_usuario,comentario_usuario
637007,Lucas Reis 602,3.9,Sem comentário
1100094,Gabriel Carvalho 581,6.2,"Aceitável, mas esperava mais."
628575,Alexandre Barbosa 220,0.3,Péssimo em todos os sentidos.
573249,Rodrigo Oliveira 273,0.5,Péssimo em todos os sentidos.
592539,Pedro Costa 181,4.8,"Não gostei, história confusa."
464493,Adriana Dias 257,0.4,Péssimo em todos os sentidos.
1199748,Eduardo Dias 177,6.0,"Poderia ser melhor, mas não é ruim."
640543,Cristina Monteiro 310,6.4,Sem comentário
599134,Larissa Lopes 330,2.6,Péssimo em todos os sentidos.
424011,Vinícius Ferreira 405,0.5,Não recomendo de jeito nenhum.


In [0]:
generos_validos = [
    "action", "adventure", "animation", "comedy", "crime", "documentary",
    "drama", "family", "fantasy", "history", "horror", "music", "mystery",
    "romance", "science fiction", "sci-fi", "tv movie", "thriller", "war", "western"
]

df_credits = spark.table("bronze.tb_credits_and_tags")

df_generos = (
    df_credits
    .select(f.col("id").cast("string").alias("id_filme"), f.col("genres").cast("string").alias("genres"))
    .withColumn("genres", f.regexp_replace("genres", ";", ","))
    .withColumn("nome_genero", f.explode(f.split("genres", ",")))
    .withColumn("nome_genero", f.trim(f.regexp_replace("nome_genero", r"[\[\]\{\}\"']", "")))
    .withColumn("_genero", f.lower("nome_genero"))
    .filter(f.col("nome_genero").isNotNull())
    .filter(f.col("nome_genero") != "")
    .filter(~f.col("nome_genero").rlike(r"^[0-9.\-]+$"))
    .filter(f.col("_genero").isin(generos_validos))
    .select("id_filme", f.initcap("nome_genero").alias("nome_genero"))
    .dropDuplicates()
)

(
    df_generos.write
    .format("delta")
    .mode("overwrite")
    .option("overwriteSchema", "true")
    .saveAsTable("silver.tb_generos")
)

display(df_generos)


id_filme,nome_genero
271110,Adventure
346364,Horror
321612,Family
260513,Action
343668,Comedy
405774,Thriller
405774,Drama
395992,Science Fiction
427641,Action
68735,Fantasy


In [0]:
def explodir_entidades(df, coluna, tipo):
    return (
        df
        .select(
            f.col("id").cast("string").alias("id_filme"),
            f.col(coluna).cast("string").alias("valor")
        )
        .withColumn("valor", f.regexp_replace("valor", ";", ","))
        .withColumn("nome_entidade", f.explode(f.split("valor", ",")))
        .withColumn("nome_entidade", f.trim(f.regexp_replace("nome_entidade", r"[\[\]\{\}\"']", "")))
        .filter(f.col("nome_entidade").isNotNull())
        .filter(f.col("nome_entidade") != "")
        .filter(~f.col("nome_entidade").rlike(r"^[0-9.\-]+$"))
        .filter(f.length("nome_entidade") >= 2)
        .filter(f.col("nome_entidade").rlike(r"[A-Za-zÀ-ÖØ-öø-ÿ\u0100-\uffff]"))
        .filter(~f.col("nome_entidade").rlike(r"(?i)https?://|www\.|[!?]|\d{4}-\d{2}-\d{2}"))
        .filter(~f.lower("nome_entidade").isin(generos_validos + [
            "released", "post production", "in production", "planned", "rumored", "canceled"
        ]))
        .filter(
            ~f.lower("nome_entidade").isin(
                "unknown", "none", "null", "n/a", "não informado", "nao informado"
            )
        )
        .withColumn("nome_entidade", f.initcap(f.lower("nome_entidade")))
        .withColumn("tipo_entidade", f.lit(tipo))
        .select("id_filme", "nome_entidade", "tipo_entidade")
    )

df_pessoas_empresas = (
    explodir_entidades(df_credits, "cast", "Ator")
    .unionByName(explodir_entidades(df_credits, "directors", "Diretor"))
    .unionByName(explodir_entidades(df_credits, "writers", "Roteirista"))
    .unionByName(explodir_entidades(df_credits, "production_companies", "Produtora"))
    .dropDuplicates()
)

(
    df_pessoas_empresas.write
    .format("delta")
    .mode("overwrite")
    .option("overwriteSchema", "true")
    .saveAsTable("silver.tb_pessoas_empresas")
)

display(df_pessoas_empresas)


id_filme,nome_entidade,tipo_entidade
296096,Vanessa Kirby,Ator
332562,Sam Elliott,Ator
423108,Patrick Wilson,Ator
399404,Lily James,Ator
453405,Benedict Wong,Ator
324849,Doug Benson,Ator
310307,Justin Randell Brooke,Ator
696806,Walker Scobell,Ator
431693,Dj Khaled,Ator
388399,John Goodman,Ator
